
# Interactive Multi-Modal Knowledge Graph Analysis
**dataset:** TENX96
**Modalities:** Image (Texture) + CUI (Semantics) + Gene (Transcriptomics)

This notebook provides a complete interactive analysis suite for:
1.  **Fusion Clustering**: Combining Morphology and Semantics.
2.  **Gene Integration**: Analyzing spatial transcriptomics and specific target markers.
3.  **Cross-Modality Comparison**: Confusion matrices and similarity heatmaps between Image, CUI, and Gene clusters.
4.  **Spatial Mapping**: Discrete clusters and continuous expression maps.
    

In [1]:

%load_ext autoreload
%autoreload 2

import os
import sys
# Add /app/src to path so we can import 'scripts' package
sys.path.append('/app/src')

import pandas as pd
import numpy as np
from scripts import KGDataLoader, MultiModalFusion, KGVisualizer

# Initialize Modules
base_dir = '/app/output'
loader = KGDataLoader(base_dir=base_dir, slide_name='TENX96')
fusion = MultiModalFusion(n_clusters=8)
viz = KGVisualizer()
    

## 1. Load Data & Pre-Processing

In [2]:

# Load Dataset (Force reload to pick up new Gene Enrichment data)
CACHE_PATH = '/app/scratchpad/dataset_cache.pkl'
df = loader.load_data(cache_path=CACHE_PATH, force_reload=False)

# Basic Stats
print(f"Loaded {len(df)} patches.")
    

Loading cached dataset from /app/scratchpad/dataset_cache.pkl...
Loaded 5124 patches from cache.
DEBUG: Found 5124/5124 patches with Image Embeddings.
DEBUG: Found 5010/5124 patches with Valid CUIs.
Validation: 5010 valid patches (from 5124 total).
Loaded 5010 patches.


## 2. Execute Modality Clustering

In [3]:

# A. Joint Fusion (Image + CUI)
df, X_fusion = fusion.process_fusion(df)

# B. Unimodal Clustering (Image Only, CUI Only) - Required for Comparison
df = fusion.compute_unimodal_clusters(df, n_clusters=8)

# C. Gene Expression Analysis (Top Expressed + Marked Panel)
marked_list = ["ESR1", "KRT8", "EGFR", "ERBB2", "MKI67", "KRT7", "PGR", "KRT5", "KRT14", "CD3D", "CD8A", "CD19"]
df, X_gene, gene_prof, marked_prof = fusion.process_gene_analysis(df, n_clusters=8, marked_genes=marked_list)
    

--- Starting Multi-Modal Fusion ---
Vectorizing CUIs...
Vocabulary size: 536 unique CUIs
Reducing dimensions (SVD=50)...


Normalizing and Fusing...
Clustering into 8 Multi-Modal Domains...

--- Domain Concept Profiles ---
Domain 0: Dermal or subcutaneous infiltrate of spindle-shaped cells arranged in a whorled pattern seen on histology, Low density lipoprotein high affinity cell surface receptor, Potentially abnormal, Sarcoma, Looser-Milkman
Domain 1: Condition, Specimen Type - Lymphocytes, Immune, Other, Inflammatory
Domain 2: Loss of Corticomedullary Distinction, adiposity, Html Link Type - section, Part, Lesion
Domain 3: Nodular (qualifier value), Formations, Chair that prevents rising, Observed, Surrounding (qualifier value)
Domain 4: Connective Tissue, Notable, Shows respect, Have, Predominantly allergic asthma
Domain 5: Characterization, Tut protein, Drosophila, Reaction, Body Regions, Disease classification level
Domain 6: Dermal or subcutaneous infiltrate of spindle-shaped cells arranged in a whorled pattern seen on histology, Low density lipoprotein high affinity cell surface receptor, Potentiall

## 3. Spatial Cluster Maps (Discrete)

In [4]:

# 1. Joint (Image + Concept)
viz.plot_spatial(df, 'joint_cluster', 'Modality: Joint (Image + CUI)').show()

# 2. Image Only (Texture)
viz.plot_spatial(df, 'img_cluster', 'Modality: Image Only').show()

# 3. Gene Only (Expression)
viz.plot_spatial(df, 'gene_cluster', 'Modality: Gene Expression').show()

# 4. CUI Only (Semantics)
viz.plot_spatial(df, 'cui_cluster', 'Modality: CUI Concepts').show()
    

## 4. Cross-Modality Overlap (Confusion Matrices)

In [5]:

# A. Gene vs Image
mat_img = fusion.compute_cluster_overlap(df, 'gene_cluster', 'img_cluster')
viz.plot_cluster_overlap(mat_img, "Overlap: Gene vs Image (Raw Count)", normalize=False).show()
viz.plot_cluster_overlap(mat_img, "Overlap: Gene vs Image (Probability)", normalize=True).show()

# B. Gene vs CUI
mat_cui = fusion.compute_cluster_overlap(df, 'gene_cluster', 'cui_cluster')
viz.plot_cluster_overlap(mat_cui, "Overlap: Gene vs CUI (Raw Count)", normalize=False).show()

# C. Gene vs Joint
mat_joint = fusion.compute_cluster_overlap(df, 'gene_cluster', 'joint_cluster')
viz.plot_cluster_overlap(mat_joint, "Overlap: Gene vs Joint (Raw Count)", normalize=False).show()
    

## 5. Biological Profiles

In [6]:

# 1. Top Expressed Genes per Cluster
viz.plot_gene_profiles(gene_prof).show()

# 2. Marked Genes (Target Panel) per Cluster
viz.plot_gene_profiles(marked_prof).show()

# 3. Top Semantic Concepts (CUI) per Cluster
cui_prof = fusion.get_top_concepts_df(df, top_n=10)
viz.plot_concept_profiles(cui_prof).show()
    

## 6. Global Similarity Comparison

In [7]:

# Compute similarity matrices for all modalities
sims = fusion.compute_all_similarities(df)
viz.plot_similarity_comparison(sims).show()
    

## 7. Continuous Spatial Gene Expression

In [8]:

# Loop through Marked Genes and plot intensity maps
print("--- Targeted Gene Maps ---")
for gene in marked_list:
    col = f'tgt_{gene}'
    if col in df.columns:
        viz.plot_continuous_spatial(df, col, title=f"Expression: {gene}").show()

# Find Top 3 Global Genes
print("--- Top Global Expressed Genes ---")
gene_cols = [c for c in df.columns if c.startswith('tgt_')]
if gene_cols:
    global_means = df[gene_cols].mean().sort_values(ascending=False)
    for col in global_means.head(3).index:
        name = col.replace('tgt_', '')
        viz.plot_continuous_spatial(df, col, title=f"Top Global: {name}").show()
    

--- Targeted Gene Maps ---


--- Top Global Expressed Genes ---


## --- Section 8: Marker Discrimination Analysis ---


In [10]:
# --- Section 8: Marker Discrimination Analysis ---
# Comparaison : Quelle modalité sépare le mieux chaque gène cible ?

# Les colonnes de clusters à comparer
cluster_cols = ['img_cluster', 'cui_cluster', 'joint_cluster', 'gene_cluster']

print("--- Marker Discrimination Scores (F-Value) & Visualisation ---")
print("Interprétation : Un F-Value élevé signifie que les clusters séparent bien les niveaux d'expression.")

for gene in marked_list:
    col = f'tgt_{gene}'
    # Vérifier si le gène existe
    if col not in df.columns: 
        print(f"Skipping {gene} (Not found)")
        continue
    
    # 1. Calculer les Scores F pour chaque modalité
    scores = {}
    for c_col in cluster_cols:
        scores[c_col] = fusion.compute_marker_discrimination(df, col, c_col)
    
    # 2. Afficher les Violin Plots comparatifs
    # Le titre de chaque sous-graphique contient le Score F
    fig = viz.plot_marker_comparison(df, col, cluster_cols, scores)
    fig.show()

--- Marker Discrimination Scores (F-Value) & Visualisation ---
Interprétation : Un F-Value élevé signifie que les clusters séparent bien les niveaux d'expression.


Skipping CD3D (Not found)


/usr/local/lib/python3.12/site-packages/sklearn/feature_selection/_univariate_selection.py:107: RuntimeWarning:

invalid value encountered in divide

/usr/local/lib/python3.12/site-packages/sklearn/feature_selection/_univariate_selection.py:107: RuntimeWarning:

invalid value encountered in divide

/usr/local/lib/python3.12/site-packages/sklearn/feature_selection/_univariate_selection.py:107: RuntimeWarning:

invalid value encountered in divide

/usr/local/lib/python3.12/site-packages/sklearn/feature_selection/_univariate_selection.py:107: RuntimeWarning:

invalid value encountered in divide



In [ ]:

# df.to_pickle('/app/scratchpad/final_dataset_augmented.pkl')
# print("Saved augmented dataset to /app/scratchpad/final_dataset_augmented.pkl")
    

Saved augmented dataset to /app/scratchpad/final_dataset_augmented.pkl


In [11]:
# --- Section 10: "Hotspot" Capture Analysis ---
# Question : Quel clustering regroupe le mieux les patchs où le gène "explose" (fortement exprimé) ?

print("--- Hotspot Capture Capability ---")
print("Analyse : On compte combien de patchs 'Hautement Exprimés' (High Exp) sont capturés par chaque cluster.")

cluster_cols = ['img_cluster', 'cui_cluster', 'joint_cluster']

for gene in marked_list:
    col = f'tgt_{gene}'
    if col not in df.columns: continue
    
    # 1. Définir "Hautement Exprimé" (Top 10% ou > Mean + 2*Std)
    threshold = df[col].mean() + 2 * df[col].std()
    high_exp_mask = df[col] > threshold
    n_high = high_exp_mask.sum()
    
    if n_high == 0:
        continue

    # 2. Pour chaque méthode de clustering, voir comment ces patchs sont répartis
    # On veut que ces patchs soient concentrés dans 1 ou 2 clusters (pas éparpillés)
    data = []
    for c_col in cluster_cols:
        # Compter les High Exp par cluster
        counts = df[high_exp_mask][c_col].value_counts()
        # Top 1 cluster capture combien de % des hotspots ?
        top_capture = counts.iloc[0] if len(counts) > 0 else 0
        p_capture = (top_capture / n_high) * 100
        
        data.append({
            'Modality': c_col, 
            'Top Cluster Capture (%)': p_capture,
            'N_Hotspots': n_high
        })
    
    # Visualisation
    import plotly.express as px
    res_df = pd.DataFrame(data)
    fig = px.bar(
        res_df, x='Modality', y='Top Cluster Capture (%)',
        title=f"Hotspot Concentration for {gene} (Higher is Better)",
        text='Top Cluster Capture (%)',
        color='Modality'
    )
    fig.update_traces(texttemplate='%{text:.1f}%', textposition='outside')
    fig.update_layout(yaxis_range=[0, 110])
    fig.show()

--- Hotspot Capture Capability ---
Analyse : On compte combien de patchs 'Hautement Exprimés' (High Exp) sont capturés par chaque cluster.


In [14]:
# --- Section 11: Modality Complementarity (Venn Analysis) ---
# Question : Est-ce que Image et CUI trouvent les mêmes patchs "forts" ?

print("--- Modality Overlap for High Expression Patches ---")
from matplotlib_venn import venn3 # Assurez-vous d'avoir installé matplotlib-venn si possible, sinon on fait du set simple

for gene in marked_list:
    col = f'tgt_{gene}'
    if col not in df.columns: continue
    
    # 1. Identifier les VRAIS Hotspots (Ground Truth)
    threshold = df[col].mean() + 2 * df[col].std()
    true_hotspots = set(df[df[col] > threshold].index)
    
    if len(true_hotspots) == 0: continue
    
    # 2. Voir quels patchs sont "sélectionnés" par le meilleur cluster de chaque méthode
    # (On prend le cluster qui a la moyenne la plus haute pour ce gène)
    
    methods = {}
    for c_col in ['img_cluster', 'cui_cluster']:
        # Trouver le cluster "champion" pour ce gène
        means = df.groupby(c_col)[col].mean()
        best_cluster = means.idxmax()
        
        # Prendre les patchs de ce cluster
        selected_patches = set(df[df[c_col] == best_cluster].index)
        
        # Garder ceux qui sont vraiment des hotspots (Precision)
        # Ou juste prendre l'intersection avec la vérité terrain pour voir ce qu'ils couvrent
        methods[c_col] = selected_patches.intersection(true_hotspots)

    # 3. Calculer les intersections
    img_set = methods['img_cluster']
    cui_set = methods['cui_cluster']
    
    only_img = len(img_set - cui_set)
    only_cui = len(cui_set - img_set)
    both = len(img_set.intersection(cui_set))
    total_found = len(img_set.union(cui_set))
    missed = len(true_hotspots) - total_found
    
    print(f"\nGene: {gene} (Total Hotspots: {len(true_hotspots)})")
    print(f"  - Captured by Image ONLY: {only_img}")
    print(f"  - Captured by CUI ONLY:   {only_cui}")
    print(f"  - Captured by BOTH:       {both}")
    print(f"  - MISSED by both:         {missed}")
    
    if only_img > only_cui:
        print("  -> IMAGE Dominance (Texture captures unique signal)")
    elif only_cui > only_img:
        print("  -> CUI Dominance (Text captures unique signal)")
    else:
        print("  -> High Redundancy (Methods agree)")

--- Modality Overlap for High Expression Patches ---

Gene: ESR1 (Total Hotspots: 70)
  - Captured by Image ONLY: 18
  - Captured by CUI ONLY:   0
  - Captured by BOTH:       3
  - MISSED by both:         49
  -> IMAGE Dominance (Texture captures unique signal)

Gene: KRT8 (Total Hotspots: 75)
  - Captured by Image ONLY: 1
  - Captured by CUI ONLY:   2
  - Captured by BOTH:       26
  - MISSED by both:         46
  -> CUI Dominance (Text captures unique signal)

Gene: EGFR (Total Hotspots: 175)
  - Captured by Image ONLY: 8
  - Captured by CUI ONLY:   18
  - Captured by BOTH:       33
  - MISSED by both:         116
  -> CUI Dominance (Text captures unique signal)

Gene: ERBB2 (Total Hotspots: 72)
  - Captured by Image ONLY: 9
  - Captured by CUI ONLY:   1
  - Captured by BOTH:       21
  - MISSED by both:         41
  -> IMAGE Dominance (Texture captures unique signal)

Gene: MKI67 (Total Hotspots: 287)
  - Captured by Image ONLY: 86
  - Captured by CUI ONLY:   44
  - Captured by BOTH